# Conda env sara_batteries

In [1]:

import os
import sys
sys.path.append(os.path.abspath("../02_scripts"))

import utils
import config



Loading core configurations...
GPU detected: NVIDIA GeForce GTX 1650 with 3.63 GB VRAM
TEST environment detected.

Current Session Configuration Summary:
  - Device: cuda
  - Embedding Model: 'all-mpnet-base-v2'
  - Classification LLM Model: 'RedHatAI/gemma-3-4b-it-quantized.w8a8'
  - Advanced LLM Model (Ext/Synth): 'RedHatAI/gemma-3-4b-it-quantized.w8a8'
  - Data File Path: '<PROJECT_ROOT>/Data/df_data_batteries_130k.parquet'



In [31]:
from bertopic import BERTopic
import dill as pickle
import pandas as pd
from umap import UMAP

study_path = os.path.join(config.PROJECT_FOLDER, "Data")
data_file = f"{config.PROJECT_FOLDER}/df_data_batteries_130k.parquet"


In [39]:
title_column = "Document Title"
abstract_column = "Abstract"
year_column = "Year Published"

data = pd.read_parquet(data_file)
data[year_column] = data[year_column].apply(lambda x: 2000+int(x) if int(x)<1000 else int(x))
data = data[["DOI", title_column, abstract_column, year_column]]
data[title_column].fillna("", inplace=True)
data[abstract_column].fillna("", inplace=True)
data.reset_index(drop=True, inplace=True)

docs = "Title: " + data[title_column] + "\n\nAbstract: " + data[abstract_column]
years = data[year_column].to_list()

with open(f'{study_path}/embs_pred.pkl', 'rb') as handle:
    embs = pickle.load(handle)

In [ ]:
model = BERTopic.load(f'{study_path}/model_pred')
print("Model loaded.")


2025-11-19 09:43:59,444 - BERTopic - WARNING: You are loading a BERTopic model without explicitly defining an embedding model. If you want to also load in an embedding model, make sure to use `BERTopic.load(my_model, embedding_model=my_embedding_model)`.


Model loaded.


In [4]:
model.get_topic_info()

,Topic,Count,Name,Representation,Aspect1,Representative_Docs
0,-1,39784,-1_Advances in Lithium-Ion Battery Anode and C...,[Advances in Lithium-Ion Battery Anode and Cat...,"[lithium, electrochemical, anodes, cathodes, c...",NaN
1,0,7618,0_Enhanced MoS2-based Anode Materials for Lith...,[Enhanced MoS2-based Anode Materials for Lithi...,"[anodes, lithium, graphene, electrochemical, n...",NaN
2,1,6548,1_High-Performance Silicon-Based Anodes for Li...,[High-Performance Silicon-Based Anodes for Lit...,"[lithiation, anodes, lithium, silicon, anode, ...",NaN
3,2,6301,2_Recycling of Valuable Metals from Spent Lith...,[Recycling of Valuable Metals from Spent Lithi...,"[recycling, lithium, battery, batteries, cobal...",NaN
4,3,6108,3_High-Performance Sodium-Ion Battery Anodes f...,[High-Performance Sodium-Ion Battery Anodes fr...,"[carbons, carbon, anodes, graphene, electroche...",NaN
5,4,5986,4_Lithium-Ion Battery State of Health Estimati...,[Lithium-Ion Battery State of Health Estimatio...,"[battery, lithium, charging, batteries, estima...",NaN
6,5,5459,5_Synthesis and Electrochemical Characterizati...,[Synthesis and Electrochemical Characterizatio...,"[li2fesio4, li3v2, lithium, electrochemical, l...",NaN
7,6,5242,6_CO2 and Additives in Lithium-Ion Battery Ele...,[CO2 and Additives in Lithium-Ion Battery Elec...,"[lithium, electrochemical, battery, electrolyt...",NaN
8,7,4754,7_High-Performance Zn Anodes for Aqueous Zinc-...,[High-Performance Zn Anodes for Aqueous Zinc-I...,"[zn2, electrochemical, anodes, zinc, electroly...",NaN
9,8,4022,8_High-Performance SnO2-Based Anodes in Lithiu...,[High-Performance SnO2-Based Anodes in Lithium...,"[nanocomposite, lithium, graphene, anodes, ele...",NaN


In [5]:
model.visualize_topics()

In [6]:
model.visualize_hierarchy()

In [ ]:
hierarchical_topics = model.hierarchical_topics(docs)
# Run the visualization with the original embeddings
model.visualize_hierarchical_documents(docs, hierarchical_topics, embeddings=embs)

# Reduce dimensionality of embeddings, this step is optional but much faster to perform iteratively:
reduced_embeddings = UMAP(n_neighbors=10, n_components=2, min_dist=0.0, metric='cosine').fit_transform(embs)
model.visualize_hierarchical_documents(docs, hierarchical_topics, reduced_embeddings=reduced_embeddings)

100%|██████████| 23/23 [00:00<00:00, 125.30it/s]


In [19]:
model.visualize_barchart(top_n_topics=4, n_words=3, autoscale=True)

In [21]:
model.visualize_heatmap()

In [ ]:
model.visualize_term_rank()

In [41]:

topics_over_time = model.topics_over_time(docs, years)
model.visualize_topics_over_time(topics_over_time)

35it [00:23,  1.49it/s]
